In [1]:
from tldhamburg.backend.DataFetcher import DataFetcher
import json

In [2]:
data_fetcher = DataFetcher()

endpoint = "Datastreams"
params = {
    "$filter": "properties/layerName eq 'primary_signal'",
    "$expand" : "Thing($expand=Locations)",
}

data_fetcher.fetch_data(endpoint,params)

print(f"Retrieved {len(data_fetcher.get_data())} datastreams.")

Retrieved 20018 datastreams.


In [3]:
print(json.dumps(data_fetcher.get_data()[0],indent=4))

{
    "@iot.selfLink": "https://tld.iot.hamburg.de/v1.1/Datastreams(62117)",
    "@iot.id": 62117,
    "name": "Primary signal heads at 1045_24",
    "description": "Datastream to broadcast the lane connection's signal value of a signal group",
    "observationType": "http://www.opengis.net/def/ogc-om/OM_CategoryObservation",
    "unitOfMeasurement": {
        "name": "Signal Status ",
        "symbol": "[0-6,9]",
        "definition": "0=dark,1=red,2=amber,3=green,4=red-amber,5=amber-flashing,6=green-flashing,9=unknown"
    },
    "observedArea": {
        "type": "Point",
        "coordinates": [
            9.9500431,
            53.5641652
        ]
    },
    "phenomenonTime": "2022-03-25T09:13:16Z/2023-03-20T08:12:05Z",
    "properties": {
        "metadata": "https://registry.gdi-de.org/id/de.hh/fa5588ec-bc36-4070-8871-6bf69365fe79",
        "layerName": "primary_signal",
        "ownerData": "Free and Hanseatic City of Hamburg",
        "serviceName": "HH_STA_traffic_lights",
 

In [4]:
data_fetcher = DataFetcher()

endpoint = "Datastreams"
params = {
    "$filter": "properties/layerName eq 'primary_signal'",
    "$select" : "id,observedArea"
}

data_fetcher.fetch_data(endpoint,params)

print(f"Retrieved {len(data_fetcher.get_data())} datastreams.")

Retrieved 20018 datastreams.


In [5]:
print(json.dumps(data_fetcher.get_data()[0],indent=4))

{
    "@iot.id": 49945,
    "observedArea": {
        "type": "Point",
        "coordinates": [
            10.0075458,
            53.520806
        ]
    }
}


In [6]:
results = dict()

for stream in data_fetcher.get_data():
    if "observedArea" not in stream.keys():
        if "noObservedArea" not in results:
            results["noObservedArea"] = 0
        results["noObservedArea"] +=1
    else: 
        type = stream["observedArea"]["type"]
        if type not in results:
            results[type] = 0
        results[type] += 1
print(results)
print(sum([value for _,value in results.items()]))


{'Point': 9047, 'LineString': 9630, 'Polygon': 1095, 'noObservedArea': 246}
20018


In [9]:
import folium
from IPython.display import display

def switch_coords(coords):
    temp = coords[0]
    coords[0] = coords[1]
    coords[1] = temp

#save possible colors for markers
colors = ['red', 'blue', 'green', 'purple', 'orange', 'darkred', 'lightred', 'beige', 'darkblue', 'darkgreen', 'cadetblue', 'darkpurple', 'white', 'pink', 'lightblue', 'lightgreen', 'gray', 'black']
def create_marker(coords,color_index):
    folium.CircleMarker(location=coords,radius=1,color = colors[color_index], fill = True, fill_color = colors[color_index], opacity = 1).add_to(map_object)
#define starting point for map (chosen arbitrarily)
hamburg_mid_point = [53.571974, 9.969119]

#create maps
map_object = folium.Map(location=hamburg_mid_point, zoom_start=12)


counter = 0
for stream in data_fetcher.get_data():
    if "observedArea" not in stream.keys():
        continue
    
    if stream["observedArea"]["type"] == "Point":
        coords = stream["observedArea"]["coordinates"]
        switch_coords(coords)
        create_marker(coords,1)
    elif stream["observedArea"]["type"] == "LineString":
        coord_pairs = stream["observedArea"]["coordinates"]
        for coords in coord_pairs:
            switch_coords(coords)  # latidute and longitude are given switch up by the API
            #add Marker for each coordinate_pair
            create_marker(coords,1)
    else:
        coord_pairs = stream["observedArea"]["coordinates"][0]
        for coords in coord_pairs:
            switch_coords(coords)  # latidute and longitude are given switch up by the API
            create_marker(coords,1)

# Display the map
display(map_object)